# 06 — Rationale Classification

Text classification on the rationale corpus to study GENRES of AI-generated rationales for translation. The unit of analysis is the rationale text itself: each row is one (service × variant × language) rationale, and the question is whether the classifier can recover service identity, prompt variant, or both from the prose alone.

After a baseline description of rationale length and lexical density, seven analytical sections follow:

1. **Variant classifier** (§6.3) — predict which prompt (`minimal`, `github_searcher`, `judge`) produced a rationale. We exclude `fluent_speaker` because it is not consistently in English. Top log-odds coefficients per class surface the rhetorical vocabulary that distinguishes each prompt style.

2. **Service classifier** (§6.4) — predict which of eight LLM services produced a rationale. Top coefficients are the prose fingerprint of each model's reasoning style.

3. **Masking ablation** (§6.5) — robustness check showing that the variant and service findings survive progressively stricter leakage masking.

4. **Stable features across seeds** (§6.6) — features in the top-15 across at least 4 of 5 random seeds, for paper-quality vocabulary tables.

5. **Joint service-variant classifier** (§6.7) — predict 24 service-variant combinations from rationale text. The marginals already work; the joint classifier surfaces the *interaction* — where prompt and service identity stop being independent. Includes a note on why causal disagreement categories are not predicted from rationales.

6. **Translation × Rationale Convergence** (§6.8) — a descriptive 2×2 frame showing how translation convergence and rationale convergence relate.

7. **Rationale embedding projection** (§6.9) — UMAP of sentence-level rationale embeddings, colored by service, prompt variant, language family, and rationale length. Complements the classifier findings with a spatial view of the rationale corpus.

All classifiers use TF-IDF (word unigrams + bigrams) + multinomial logistic regression. Coefficients are directly interpretable as log-odds ratios, so top features can be read as a ranked vocabulary list rather than a black-box importance score.

Input:
- `translated_terms/digital_humanities/evaluation/disagreement_explorer_data.csv`
- `translated_terms/digital_humanities/evaluation/disagreement_analysis.csv`
**Exclusion tier: Tier 2 — Translation & Rationale Analysis** (see [docs/exclusion_strategy.md](../docs/exclusion_strategy.md))

Manual `exclude_translation=True` drops the entire (language × service) entry from the rationale corpus. Manual `exclude_rationale_{variant}=True` drops that specific (language × service × variant) rationale while leaving other variants for the same service intact.

## 6.1 Setup & Data Load

In [1]:
import os
import re
import sys
from pathlib import Path

import numpy as np
import pandas as pd
import altair as alt

alt.data_transformers.enable("vegafusion")

sys.path.insert(0, str(Path("..").resolve()))
from scripts.utils import get_data_directory_path, read_csv_file, save_chart
from scripts.exploration.rationale_classifier import (
    ENGLISH_VARIANTS,
    SERVICES,
    mask_prompt_metadata,
    build_tfidf,
    train_classifier,
    top_coefficients,
    confusion_df,
    MaskingConfig,
    PRESET_NONE, PRESET_NAMES_ONLY, PRESET_STANDARD, PRESET_AGGRESSIVE,
    apply_masking,
    run_masking_ablation,
    stable_features,
)

In [2]:
DATA_DIR  = get_data_directory_path()
TERM_SLUG = "digital_humanities"
EVAL_DIR  = os.path.join(DATA_DIR, "translated_terms", TERM_SLUG, "evaluation")
FIGURE_DIR = Path("..") / "figures" / "dhq_article"
FIGURE_DIR.mkdir(parents=True, exist_ok=True)

EXPLORER_CSV = os.path.join(EVAL_DIR, "disagreement_explorer_data.csv")
ANALYSIS_CSV = os.path.join(EVAL_DIR, "disagreement_analysis.csv")

print(f"Explorer: {EXPLORER_CSV}")
print(f"Analysis: {ANALYSIS_CSV}")
EXCL_PATH    = os.path.join(EVAL_DIR, 'manual_exclusions.csv')


Retrieving translation pipeline data directory path...

Explorer: /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/datasets/translated_terms/digital_humanities/evaluation/disagreement_explorer_data.csv
Analysis: /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/datasets/translated_terms/digital_humanities/evaluation/disagreement_analysis.csv


In [3]:
explorer_df = read_csv_file(EXPLORER_CSV)
analysis_df = read_csv_file(ANALYSIS_CSV)

print(f"Explorer: {len(explorer_df):,} rows, {len(explorer_df.columns)} columns")
print(f"Analysis: {len(analysis_df):,} rows")
print(f"\nComparison-status distribution (analysis):")
print(analysis_df["comparison_status"].value_counts().to_string())

# ── Language count sanity check (pre-exclusion) ─────────────────────────────
_n = analysis_df['language_code'].nunique()
print(f'\nLanguages loaded (pre-exclusion): {_n} (expected 881)')
if _n != 881:
    print(f'  ⚠ Expected 880 — re-run the translation pipeline or check for missing/duplicate language_code rows.')
else:
    print(f'  ✓ Count matches expected 881.')

Explorer: 881 rows, 111 columns
Analysis: 881 rows

Comparison-status distribution (analysis):
comparison_status
substantive_variation    873
exact_convergence          5
near_form_convergence      3

Languages loaded (pre-exclusion): 881 (expected 881)
  ✓ Count matches expected 881.


In [4]:
# ── Manual exclusion summary ────────────────────────────────────────────────
from scripts.utils import load_manual_exclusions as lme

analysis_terms, search_terms, _corrections = lme(EVAL_DIR)
print(f"Manual exclusions loaded:")
print(f"  analysis_exclusion : {len(analysis_terms)} (language, term) pairs  (terms excluded from rationale analysis)")
print(f"  search_exclusion   : {len(search_terms)} (language, term) pairs")
print(f"  term_correction    : {len(_corrections)} corrections")

Manual exclusions loaded:
  analysis_exclusion : 122 (language, term) pairs  (terms excluded from rationale analysis)
  search_exclusion   : 383 (language, term) pairs
  term_correction    : 94 corrections


In [5]:
# ── Tier 2 rationale exclusions ─────────────────────────────────────────────
# Build a (language_code, service_lower) → {translation, rationale_*} dict.
# Service names in manual_exclusions.csv are title-cased; rationale columns
# use lowercase service names, so we normalise to lowercase for lookup.

rat_excl_lookup = {}  # (lc, svc_lower) → {'translation': bool, 'rationale_minimal': bool, ...}
if os.path.exists(EXCL_PATH):
    excl = read_csv_file(EXCL_PATH)
    rat_variants = ['minimal', 'fluent_speaker', 'github_searcher', 'judge']
    for _, row in excl.iterrows():
        lc  = row.get('language_code', '')
        svc = str(row.get('service', '')).strip().lower()
        if not lc or not svc or svc == 'nan':
            continue
        rat_excl_lookup[(lc, svc)] = {
            'translation': str(row.get('exclude_translation', 'False')).strip().lower() == 'true',
            **{f'rationale_{v}': str(row.get(f'exclude_rationale_{v}', 'False')).strip().lower() == 'true'
               for v in rat_variants},
        }

n_trans_drops = sum(1 for e in rat_excl_lookup.values() if e['translation'])
n_rat_drops   = sum(1 for e in rat_excl_lookup.values()
                    for k, v in e.items() if k.startswith('rationale_') and v)
print(f'Tier 2 rationale exclusions loaded:')
print(f'  exclude_translation entries : {n_trans_drops}')
print(f'  exclude_rationale_* entries : {n_rat_drops}')


Tier 2 rationale exclusions loaded:
  exclude_translation entries : 96
  exclude_rationale_* entries : 0


## 6.2 Long-Format Prep

Melt the wide rationale CSV into one row per (language × service × variant). `fluent_speaker` is excluded throughout: its rationales are written in the target language, so the classifier would learn script identity rather than rhetorical style.

After melting, `mask_prompt_metadata()` strips variant and service name tokens (`minimal`, `github_searcher`, `judge`, `fluent_speaker`, `claude`, `openai`, `gemini`, `deepseek`, `llama`, `gemma`, `qwen`, `mistral`) from every rationale. This is necessary because the `judge` prompt supplies all variant and service names as explicit labels in its context window, and models echo them verbatim, creating direct label leakage into the feature space.

In [6]:
# Identify rationale columns for English variants only
ENGLISH_VARIANT_PAT = re.compile(
    r"^(claude|openai|gemini|deepseek|llama|gemma|qwen|mistral)_rationale_(minimal|github_searcher|judge)$"
)
rat_cols = [c for c in explorer_df.columns if ENGLISH_VARIANT_PAT.match(c)]
print(f"Rationale columns to use: {len(rat_cols)}")
for c in rat_cols:
    print(f"  {c}")

Rationale columns to use: 24
  deepseek_rationale_minimal
  openai_rationale_minimal
  qwen_rationale_minimal
  gemma_rationale_minimal
  mistral_rationale_minimal
  gemini_rationale_minimal
  claude_rationale_minimal
  llama_rationale_minimal
  deepseek_rationale_github_searcher
  openai_rationale_github_searcher
  qwen_rationale_github_searcher
  gemma_rationale_github_searcher
  mistral_rationale_github_searcher
  gemini_rationale_github_searcher
  claude_rationale_github_searcher
  llama_rationale_github_searcher
  deepseek_rationale_judge
  openai_rationale_judge
  qwen_rationale_judge
  gemma_rationale_judge
  mistral_rationale_judge
  gemini_rationale_judge
  claude_rationale_judge
  llama_rationale_judge


In [7]:
id_cols = ["language_code", "language_name", "language_family"]

long_rows = []
for col in rat_cols:
    m = ENGLISH_VARIANT_PAT.match(col)
    service, variant = m.group(1), m.group(2)
    sub = explorer_df[id_cols + [col]].dropna(subset=[col]).copy()
    sub = sub[
        ~sub[col].astype(str).str.strip().isin({"No rationale provided", "[rationale truncated — MAX_TOKENS]"})
        & (sub[col].astype(str).str.len() > 20)
    ]
    # Tier 2: drop excluded (language × service) and (language × service × variant) entries
    sub = sub[~sub["language_code"].apply(
        lambda lc: rat_excl_lookup.get((lc, service), {}).get("translation", False)
                or rat_excl_lookup.get((lc, service), {}).get(f"rationale_{variant}", False)
    )].copy()
    sub["service"] = service
    sub["variant"] = variant
    sub["rationale_raw"] = sub[col].astype(str)
    long_rows.append(sub.drop(columns=[col]))

long_df = pd.concat(long_rows, ignore_index=True)

# Delete variant and service name tokens to prevent judge-prompt label leakage. We DELETE rather than replace with a placeholder: placeholders like [SERVICE] are stripped of brackets by TF-IDF's tokenizer, leaving 'service'/'variant' as spurious features that contaminate the classifier.
long_df["rationale_clean"] = long_df["rationale_raw"].apply(mask_prompt_metadata)

print(f"Long-format rows: {len(long_df):,}")
print(f"\nBy variant:")
print(long_df["variant"].value_counts().to_string())
print(f"\nBy service:")
print(long_df["service"].value_counts().to_string())

# Leakage check — all counts should be 0 after masking
LEAK_TOKENS = ["fluent_speaker", "github_searcher", "openai", "claude", "gemini", "deepseek", "llama", "gemma", "qwen", "mistral"]
print("\nLeakage check (should all be 0 after masking):")
for tok in LEAK_TOKENS:
    before = long_df["rationale_raw"].str.contains(rf"\b{tok}\b", case=False, regex=True).sum()
    after  = long_df["rationale_clean"].str.contains(rf"\b{tok}\b", case=False, regex=True).sum()
    status = "✓" if after == 0 else "✗"
    print(f"  {status} {tok:<20}  before: {before:>4}   after: {after}")

Long-format rows: 20,661

By variant:
variant
judge              7033
github_searcher    6894
minimal            6734

By service:
service
claude      2642
qwen        2635
deepseek    2626
gemma       2616
mistral     2587
gemini      2563
openai      2547
llama       2445

Leakage check (should all be 0 after masking):
  ✓ fluent_speaker        before: 1712   after: 0
  ✗ github_searcher       before: 1077   after: 1
  ✗ openai                before: 1628   after: 3
  ✗ claude                before: 2531   after: 1


  ✗ gemini                before: 1659   after: 3
  ✗ deepseek              before: 1724   after: 3
  ✗ llama                 before:  793   after: 1
  ✓ gemma                 before:  821   after: 0
  ✓ qwen                  before:  611   after: 0


  ✗ mistral               before:  754   after: 1


### Baseline Rationale Length and Lexical Density

Before classifying rhetorical style, I establish how much prose each service and prompt produces. Length is the number of Unicode word tokens in a rationale. Lexical density is the share of those tokens that are not in scikit-learn's English stop-word list. It approximates content-word concentration, not factual content or reasoning quality, and should be interpreted cautiously when an English rationale contains substantial target-language text. Medians and interquartile ranges reduce the influence of unusually long generations and repetition loops.

In [8]:
from sklearn.feature_extraction.text import ENGLISH_STOP_WORDS

WORD_RE = re.compile(r"[^\W\d_]+(?:['’][^\W\d_]+)?", flags=re.UNICODE)

def rationale_surface_metrics(text):
    tokens = WORD_RE.findall(str(text))
    lowered = [token.lower() for token in tokens]
    n_words = len(lowered)
    n_content = sum(token not in ENGLISH_STOP_WORDS for token in lowered)
    return pd.Series({
        'word_count': n_words,
        'character_count': len(str(text).strip()),
        'lexical_density': n_content / n_words if n_words else np.nan,
    })

surface_metrics = long_df['rationale_raw'].apply(rationale_surface_metrics)
long_df = pd.concat([long_df.drop(columns=surface_metrics.columns, errors='ignore'), surface_metrics], axis=1)

def summarize_surface(group_cols):
    return (
        long_df.groupby(group_cols, observed=True)
        .agg(
            n_rationales=('rationale_raw', 'size'),
            median_words=('word_count', 'median'),
            q1_words=('word_count', lambda s: s.quantile(0.25)),
            q3_words=('word_count', lambda s: s.quantile(0.75)),
            median_lexical_density=('lexical_density', 'median'),
        )
        .reset_index()
    )

length_by_variant = summarize_surface(['variant'])
length_by_service = summarize_surface(['service'])
length_by_service_variant = summarize_surface(['service', 'variant'])

print('Rationale surface metrics by prompt variant:')
display(length_by_variant.round({'median_words': 1, 'q1_words': 1, 'q3_words': 1, 'median_lexical_density': 3}))
print('Rationale surface metrics by service:')
display(length_by_service.round({'median_words': 1, 'q1_words': 1, 'q3_words': 1, 'median_lexical_density': 3}))

surface_plot = length_by_service_variant.copy()
surface_variant_labels = {'minimal': 'Minimal', 'github_searcher': 'GitHub searcher', 'judge': 'Judge'}
surface_service_labels = {
    'claude': 'Claude', 'openai': 'OpenAI', 'gemini': 'Gemini', 'deepseek': 'DeepSeek',
    'llama': 'Llama', 'gemma': 'Gemma', 'qwen': 'Qwen', 'mistral': 'Mistral',
}
surface_plot['prompt'] = surface_plot['variant'].map(surface_variant_labels)
surface_plot['model'] = surface_plot['service'].map(surface_service_labels)
surface_variant_order = [surface_variant_labels[variant] for variant in ENGLISH_VARIANTS]
surface_service_order = [surface_service_labels[service] for service in SERVICES]
surface_plot['median_words_label'] = surface_plot['median_words'].round().astype(int).astype(str)
surface_plot['density_label'] = surface_plot['median_lexical_density'].map(lambda value: f'{value:.2f}')

word_base = alt.Chart(surface_plot).encode(
    x=alt.X('prompt:N', sort=surface_variant_order, title='Prompt variant'),
    y=alt.Y('model:N', sort=surface_service_order, title='Service'),
)
word_heat = word_base.mark_rect().encode(
    color=alt.Color('median_words:Q', scale=alt.Scale(scheme='blues'), title='Median words'),
) + word_base.mark_text(fontSize=11).encode(
    text='median_words_label:N',
    color=alt.condition(alt.datum.median_words > 130, alt.value('white'), alt.value('black')),
)
word_heat = word_heat.properties(width=260, height=300, title='Median rationale word count')

density_base = alt.Chart(surface_plot).encode(
    x=alt.X('prompt:N', sort=surface_variant_order, title='Prompt variant'),
    y=alt.Y('model:N', sort=surface_service_order, title=None),
)
density_heat = density_base.mark_rect().encode(
    color=alt.Color('median_lexical_density:Q', scale=alt.Scale(scheme='greens'), title='Content-word share'),
) + density_base.mark_text(fontSize=11).encode(
    text='density_label:N',
    color=alt.value('black'),
)
density_heat = density_heat.properties(width=260, height=300, title='Median lexical density')

rationale_surface_chart = (word_heat | density_heat).resolve_scale(color='independent').properties(
    title=alt.TitleParams(
        'Rationale Length and Lexical Density by Service and Prompt',
        subtitle='Cells show medians; lexical density = non-stopword word tokens / all word tokens.',
        subtitleColor='#666', subtitleFontSize=11,
    )
)
save_chart(rationale_surface_chart, str(FIGURE_DIR / 'rationale_length_density_by_service_prompt.png'))
rationale_surface_chart

Rationale surface metrics by prompt variant:


,variant,n_rationales,median_words,q1_words,q3_words,median_lexical_density
0,github_searcher,6894,47.0,33.0,65.0,0.622
1,judge,7033,101.0,67.0,198.0,0.611
2,minimal,6734,60.0,46.0,81.0,0.616


Rationale surface metrics by service:


,service,n_rationales,median_words,q1_words,q3_words,median_lexical_density
0,claude,2642,85.0,64.0,170.0,0.679
1,deepseek,2626,65.0,42.0,103.0,0.667
2,gemini,2563,116.0,75.5,410.0,0.615
3,gemma,2616,103.5,64.0,237.2,0.620
4,llama,2445,52.0,36.0,73.0,0.596
5,mistral,2587,39.0,29.0,51.0,0.594
6,openai,2547,65.0,51.0,84.0,0.578
7,qwen,2635,45.0,31.0,56.0,0.583


alt.HConcatChart(...)

## 6.3 Variant Classifier

Can the model identify which prompt produced the rationale from the text alone? High accuracy means the three prompts elicit genuinely different rhetorical styles. The top positive coefficients per class are the vocabulary the classifier learned. These can be read directly as a ranked keyword list for each prompt genre.

A logistic regression classifier is deliberately chosen: its coefficients are directly interpretable as log-odds ratios, so no post-hoc feature explanation technique is needed.

In [9]:
texts_var  = long_df["rationale_clean"].tolist()
labels_var = long_df["variant"].tolist()

X_var, vec_var = build_tfidf(texts_var, min_df=5)
y_var = np.array(labels_var)

print(f"Feature matrix: {X_var.shape[0]:,} rows × {X_var.shape[1]:,} features")
print(f"Class distribution: {pd.Series(y_var).value_counts().to_dict()}")

Feature matrix: 20,661 rows × 15,000 features
Class distribution: {'judge': 7033, 'github_searcher': 6894, 'minimal': 6734}


In [10]:
clf_var, cv_var, oof_var = train_classifier(X_var, y_var)

print(f"Cross-validated macro-F1 (5-fold): {cv_var.mean():.3f} ± {cv_var.std():.3f}")
print(f"Per-fold: {[round(s, 3) for s in cv_var]}")
print()
print("Interpretation: macro-F1 > 0.5 means the classifier does better than chance")
print("across all three variants. Near-perfect scores (~0.9+) indicate the prompt")
print("variants produce highly distinctive rhetorical styles.")

Cross-validated macro-F1 (5-fold): 0.896 ± 0.005
Per-fold: [np.float64(0.903), np.float64(0.893), np.float64(0.901), np.float64(0.898), np.float64(0.888)]

Interpretation: macro-F1 > 0.5 means the classifier does better than chance
across all three variants. Near-perfect scores (~0.9+) indicate the prompt
variants produce highly distinctive rhetorical styles.


In [11]:
# Out-of-fold confusion matrix — recall-normalised (% of true class)
VARIANT_ORDER = ["minimal", "github_searcher", "judge"]
cm_var_df = confusion_df(y_var, oof_var, labels=VARIANT_ORDER)

base_v = alt.Chart(cm_var_df).encode(
    x=alt.X("predicted:N", sort=VARIANT_ORDER, title="Predicted",
            axis=alt.Axis(labelAngle=-20)),
    y=alt.Y("true:N", sort=VARIANT_ORDER, title="True"),
    tooltip=["true:N", "predicted:N", "n:Q",
             alt.Tooltip("pct:Q", format=".1f", title="% of true class")],
)
rect_v = base_v.mark_rect().encode(
    color=alt.Color("pct:Q", scale=alt.Scale(scheme="blues"), title="% of true class"),
)
text_v = base_v.mark_text(fontSize=12).encode(
    text=alt.Text("pct:Q", format=".0f"),
    color=alt.condition(alt.datum.pct > 60, alt.value("white"), alt.value("black")),
)
(rect_v + text_v).properties(
    width=280, height=220,
    title="Variant classifier — out-of-fold confusion matrix (% of true class)",
)

alt.LayerChart(...)

In [12]:
coef_var = top_coefficients(clf_var, vec_var, VARIANT_ORDER, top_n=30)

# Print top 30 terms per variant
for variant in VARIANT_ORDER:
    print(f"\n{'='*50}")
    print(f"  {variant.upper()}  — top 30 log-odds features")
    print(f"{'='*50}")
    for rank, (term, weight) in enumerate(coef_var[variant], 1):
        print(f"  {rank:>2}. {term:<35} {weight:+.4f}")

coef_rows_v = [
    {"variant": v, "term": term, "weight": weight}
    for v, pairs in coef_var.items()
    for term, weight in pairs
]
coef_df_v = pd.DataFrame(coef_rows_v)




  MINIMAL  — top 30 log-odds features
   1. github                              +5.8581
   2. search                              +5.5250
   3. translation digital                 +3.9581
   4. translation based                   +3.2424
   5. translated                          +3.1886
   6. equivalent digital                  +2.8700
   7. translation combines                +2.7255
   8. query                               +2.7069
   9. contexts                            +2.6358
  10. search query                        +2.5869
  11. combination aims                    +2.5822
  12. scholarship                         +2.5480
  13. direct                              +2.5428
  14. iso code                            +2.3662
  15. recognizable                        +2.2289
  16. speaking                            +2.1834
  17. content                             +2.1643
  18. searching                           +2.0670
  19. searches                            +2.0156
  20. based

In [13]:
alt.Chart(coef_df_v).mark_bar().encode(
    x=alt.X("weight:Q", title="Log-odds coefficient"),
    y=alt.Y("term:N", sort="-x", title=None),
    color=alt.Color("variant:N", scale=alt.Scale(scheme="tableau10"), legend=None),
    tooltip=["variant:N", "term:N", alt.Tooltip("weight:Q", format=".3f")],
).facet(
    facet=alt.Facet("variant:N", sort=VARIANT_ORDER, title=None),
    columns=3,
).properties(
    title="Top 30 positive log-odds features per prompt variant",
)

alt.FacetChart(...)

## 6.4 Service Classifier

Can the model tell which LLM service produced a rationale from the text alone? High accuracy means the four services have genuinely distinct writing styles or knowledge patterns. Low accuracy means they are rhetorically interchangeable, the prompt variant matters more than who answered it.

Same TF-IDF + logistic regression setup as the variant classifier.

In [14]:
texts_svc  = long_df["rationale_clean"].tolist()
labels_svc = long_df["service"].tolist()

X_svc, vec_svc = build_tfidf(texts_svc, min_df=5)
y_svc = np.array(labels_svc)

print(f"Feature matrix: {X_svc.shape[0]:,} rows × {X_svc.shape[1]:,} features")
print(f"Class distribution: {pd.Series(y_svc).value_counts().to_dict()}")

clf_svc, cv_svc, oof_svc = train_classifier(X_svc, y_svc)

print(f"\nCross-validated macro-F1 (5-fold): {cv_svc.mean():.3f} ± {cv_svc.std():.3f}")
print(f"Per-fold: {[round(s, 3) for s in cv_svc]}")
print()
print("Interpretation: macro-F1 > 0.25 (4-class chance) means services produce")
print("detectably different rhetorical styles.")

Feature matrix: 20,661 rows × 15,000 features
Class distribution: {'claude': 2642, 'qwen': 2635, 'deepseek': 2626, 'gemma': 2616, 'mistral': 2587, 'gemini': 2563, 'openai': 2547, 'llama': 2445}



Cross-validated macro-F1 (5-fold): 0.942 ± 0.002
Per-fold: [np.float64(0.945), np.float64(0.94), np.float64(0.943), np.float64(0.945), np.float64(0.939)]

Interpretation: macro-F1 > 0.25 (4-class chance) means services produce
detectably different rhetorical styles.


In [15]:
SVC_ORDER = sorted(long_df["service"].unique())
cm_svc_df = confusion_df(y_svc, oof_svc, labels=SVC_ORDER)

base_s = alt.Chart(cm_svc_df).encode(
    x=alt.X("predicted:N", sort=SVC_ORDER, title="Predicted",
            axis=alt.Axis(labelAngle=-20)),
    y=alt.Y("true:N", sort=SVC_ORDER, title="True"),
    tooltip=["true:N", "predicted:N", "n:Q",
             alt.Tooltip("pct:Q", format=".1f", title="% of true class")],
)
rect_s = base_s.mark_rect().encode(
    color=alt.Color("pct:Q", scale=alt.Scale(scheme="blues"), title="% of true class"),
)
text_s = base_s.mark_text(fontSize=12).encode(
    text=alt.Text("pct:Q", format=".0f"),
    color=alt.condition(alt.datum.pct > 60, alt.value("white"), alt.value("black")),
)
(rect_s + text_s).properties(
    width=280, height=220,
    title="Service classifier — out-of-fold confusion matrix (% of true class)",
)

alt.LayerChart(...)

In [16]:
coef_svc = top_coefficients(clf_svc, vec_svc, SVC_ORDER, top_n=30)

# Print top 30 terms per service
for svc in SVC_ORDER:
    print(f"\n{'='*50}")
    print(f"  {svc.upper()}  — top 30 log-odds features")
    print(f"{'='*50}")
    for rank, (term, weight) in enumerate(coef_svc[svc], 1):
        print(f"  {rank:>2}. {term:<35} {weight:+.4f}")

coef_rows_s = [
    {"service": s, "term": term, "weight": weight}
    for s, pairs in coef_svc.items()
    for term, weight in pairs
]
coef_df_s = pd.DataFrame(coef_rows_s)

alt.Chart(coef_df_s).mark_bar().encode(
    x=alt.X("weight:Q", title="Log-odds coefficient"),
    y=alt.Y("term:N", sort="-x", title=None),
    color=alt.Color("service:N", scale=alt.Scale(scheme="category10"), legend=None),
    tooltip=["service:N", "term:N", alt.Tooltip("weight:Q", format=".3f")],
).facet(
    facet=alt.Facet("service:N", sort=SVC_ORDER, title=None),
    columns=2,
).properties(
    title="Top 30 positive log-odds features per service",
)


  CLAUDE  — top 30 log-odds features
   1. follows                             +5.9700
   2. terminology                         +5.7157
   3. academic                            +4.7420
   4. human                               +4.1922
   5. alternative                         +4.1848
   6. sciences                            +4.0487
   7. patterns                            +3.8492
   8. academic terminology                +3.7664
   9. knowledge                           +3.7614
  10. github                              +3.3339
  11. technical                           +3.2416
  12. academic contexts                   +2.8094
  13. established                         +2.7909
  14. typically                           +2.6310
  15. learning                            +2.5366
  16. standard                            +2.5042
  17. proper                              +2.4523
  18. conventions                         +2.4057
  19. speakers                            +2.3941
  20. borrow

alt.FacetChart(...)

## 6.5 Masking Ablation — Robustness of the Variant and Service Findings

The variant and service classifiers achieve very high accuracy on rationales already cleaned of variant/service name leakage (§6.2). But how much of that accuracy survives stricter masking, stripping the source term ("Digital Humanities"), language names, even per-row translated terms?

This section runs the same two classification tasks under four masking presets:

- **NONE** — raw rationale text, no masking. Reports the upper-bound F1.
- **NAMES_ONLY** — strip variant + service name tokens (the §6.2 default).
- **STANDARD** — NAMES_ONLY + strip source-term unigrams + language names.
- **AGGRESSIVE** — STANDARD + strip source-term bigrams + per-row translation.


In [17]:
# Variant ablation across four masking presets
print("\n████ VARIANT CLASSIFIER ABLATION ████")
variant_ablation = run_masking_ablation(
    long_df,
    text_col="rationale_raw",
    label_col="variant",
    class_order=list(ENGLISH_VARIANTS),
    top_n_features=20,
    verbose=True,
)
variant_ablation.to_csv(os.path.join(EVAL_DIR, "variant_ablation_results.csv"), index=False)
print(f"\n→ Saved {os.path.join(EVAL_DIR, 'variant_ablation_results.csv')}")


████ VARIANT CLASSIFIER ABLATION ████



══ NONE | macro-F1 = 0.896 ± 0.005 ══
           minimal: github(+6.03), search(+5.59), translation digital(+3.88), translation based(+3.22), translated(+3.15), equivalent digital(+2.84), query(+2.75), translation combines(+2.68), search query(+2.63), combination aims(+2.61)
   github_searcher: translations(+7.38), proposed(+6.46), choice(+4.41), proposed translations(+4.33), claude(+4.21), sources(+4.09), accurate(+3.89), aligns(+3.47), consistent(+3.43), fluent_speaker(+3.40)
             judge: iso(+7.79), breakdown(+5.29), term digital(+3.42), alternative(+2.70), literally(+2.47), modern(+2.44), translation aims(+2.36), digital translates(+2.35), humanities translated(+2.27), 其中(+2.10)



══ NAMES_ONLY | macro-F1 = 0.896 ± 0.005 ══
           minimal: github(+5.86), search(+5.52), translation digital(+3.96), translation based(+3.24), translated(+3.19), equivalent digital(+2.87), translation combines(+2.73), query(+2.71), contexts(+2.64), search query(+2.59)
   github_searcher: translations(+7.59), proposed(+6.86), sources(+4.51), choice(+4.40), proposed translations(+4.39), accurate(+4.16), consistent(+3.56), aligns(+3.54), accurately(+3.40), appropriate(+3.34)
             judge: iso(+7.63), breakdown(+5.31), term digital(+3.46), alternative(+2.67), literally(+2.54), modern(+2.52), translation aims(+2.36), digital translates(+2.32), humanities translated(+2.31), 其中(+2.07)



══ STANDARD | macro-F1 = 0.899 ± 0.005 ══
           minimal: github(+5.65), search(+5.40), translation based(+3.69), translated(+2.79), translation using(+2.66), direct(+2.66), translation combines(+2.66), query(+2.63), contexts(+2.60), scholarship(+2.54)
   github_searcher: translations(+7.48), proposed(+6.79), choice(+4.43), sources(+4.38), proposed translations(+4.34), accurate(+3.99), aligns(+3.51), consistent(+3.42), best(+3.27), agreed(+3.27)
             judge: iso(+6.91), breakdown(+5.10), alternative(+2.80), term translated(+2.42), literally(+2.40), translation aims(+2.32), modern(+2.26), 其中(+2.18), translation breaks(+2.07), rendered(+2.04)



══ AGGRESSIVE | macro-F1 = 0.899 ± 0.005 ══
           minimal: github(+5.65), search(+5.40), translation based(+3.69), translated(+2.79), translation using(+2.66), direct(+2.66), translation combines(+2.66), query(+2.63), contexts(+2.60), scholarship(+2.54)
   github_searcher: translations(+7.48), proposed(+6.79), choice(+4.43), sources(+4.38), proposed translations(+4.34), accurate(+3.99), aligns(+3.51), consistent(+3.42), best(+3.27), agreed(+3.27)
             judge: iso(+6.91), breakdown(+5.10), alternative(+2.80), term translated(+2.42), literally(+2.40), translation aims(+2.32), modern(+2.26), 其中(+2.18), translation breaks(+2.07), rendered(+2.04)

→ Saved /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/datasets/translated_terms/digital_humanities/evaluation/variant_ablation_results.csv


In [18]:
# Service ablation across four masking presets
print("\n████ SERVICE CLASSIFIER ABLATION ████")
service_ablation = run_masking_ablation(
    long_df,
    text_col="rationale_raw",
    label_col="service",
    class_order=list(SERVICES),
    top_n_features=20,
    verbose=True,
)
service_ablation.to_csv(os.path.join(EVAL_DIR, "service_ablation_results.csv"), index=False)
print(f"\n→ Saved {os.path.join(EVAL_DIR, 'service_ablation_results.csv')}")


████ SERVICE CLASSIFIER ABLATION ████



══ NONE | macro-F1 = 0.943 ± 0.002 ══
            claude: follows(+5.95), terminology(+5.69), academic(+4.74), alternative(+4.21), human(+4.16), sciences(+4.03), patterns(+3.84), academic terminology(+3.76), knowledge(+3.74), github(+3.33)
            openai: standard(+4.47), reflecting(+4.10), academic(+3.34), field(+3.25), humanities commonly(+3.23), adapted(+3.20), uses(+3.12), interdisciplinary(+3.05), nonsensical(+2.97), evaluating proposed(+2.97)
            gemini: direct(+5.99), directly(+4.02), direct accurate(+3.94), understood(+3.87), like(+3.42), common(+3.27), plural(+3.13), languages(+3.12), academic(+2.97), approach(+2.88)
          deepseek: core(+4.97), breakdown(+4.49), options(+3.96), aims(+3.82), core meaning(+3.71), combining creates(+3.55), understandable(+3.41), common(+3.35), doesn(+3.29), creates(+3.27)
             llama: best translation(+4.63), word(+3.50), humanities translated(+3.48), translated literally(+3.35), arts(+3.18), words(+3.07), based(+3.07), h


══ NAMES_ONLY | macro-F1 = 0.942 ± 0.002 ══
            claude: follows(+5.97), terminology(+5.72), academic(+4.74), human(+4.19), alternative(+4.18), sciences(+4.05), patterns(+3.85), academic terminology(+3.77), knowledge(+3.76), github(+3.33)
            openai: standard(+4.45), reflecting(+4.09), academic(+3.33), field(+3.22), adapted(+3.19), humanities commonly(+3.19), uses(+3.17), nonsensical(+3.10), interdisciplinary(+3.04), non(+3.01)
            gemini: direct(+5.99), directly(+4.02), direct accurate(+3.94), understood(+3.86), like(+3.43), common(+3.31), plural(+3.15), languages(+3.13), academic(+2.98), widely understood(+2.87)
          deepseek: core(+4.99), breakdown(+4.52), options(+3.96), aims(+3.84), core meaning(+3.72), combining creates(+3.55), understandable(+3.42), common(+3.36), doesn(+3.28), creates(+3.28)
             llama: best translation(+4.77), word(+3.48), humanities translated(+3.42), translated literally(+3.32), arts(+3.19), based(+3.08), words(+3.07), hu


══ STANDARD | macro-F1 = 0.946 ± 0.003 ══
            claude: follows(+5.68), terminology(+5.42), alternative(+4.39), academic(+4.32), human(+4.09), sciences(+3.97), patterns(+3.73), academic terminology(+3.57), knowledge(+3.55), technical(+3.20)
            openai: reflecting(+4.31), standard(+3.98), field(+3.41), academic(+3.36), uses(+3.31), interdisciplinary(+3.12), nonsensical(+3.07), non(+3.00), evaluating proposed(+3.00), unrelated(+2.96)
            gemini: direct(+6.01), direct accurate(+3.93), directly(+3.80), understood(+3.71), like(+3.33), common(+3.27), plural(+3.17), languages(+3.03), academic(+2.85), adjective(+2.82)
          deepseek: core(+4.82), breakdown(+4.44), options(+3.97), aims(+3.68), core meaning(+3.56), combining creates(+3.56), transliteration(+3.38), understandable(+3.37), signifies(+3.35), common(+3.31)
             llama: best translation(+4.70), word(+3.60), translated(+3.56), translated literally(+3.54), arts(+3.29), combining(+2.80), translation engl


══ AGGRESSIVE | macro-F1 = 0.946 ± 0.003 ══
            claude: follows(+5.68), terminology(+5.42), alternative(+4.39), academic(+4.32), human(+4.09), sciences(+3.97), patterns(+3.73), academic terminology(+3.57), knowledge(+3.55), technical(+3.20)
            openai: reflecting(+4.31), standard(+3.98), field(+3.41), academic(+3.36), uses(+3.31), interdisciplinary(+3.12), nonsensical(+3.07), non(+3.00), evaluating proposed(+3.00), unrelated(+2.96)
            gemini: direct(+6.01), direct accurate(+3.93), directly(+3.80), understood(+3.71), like(+3.33), common(+3.27), plural(+3.17), languages(+3.03), academic(+2.85), adjective(+2.82)
          deepseek: core(+4.82), breakdown(+4.44), options(+3.97), aims(+3.68), core meaning(+3.56), combining creates(+3.56), transliteration(+3.38), understandable(+3.37), signifies(+3.35), common(+3.31)
             llama: best translation(+4.70), word(+3.60), translated(+3.56), translated literally(+3.54), arts(+3.29), combining(+2.80), translation en

In [19]:
# Visualize: macro-F1 across masking presets, both tasks
ablation_summary = pd.concat([
    variant_ablation.drop_duplicates("masking")[["masking", "cv_f1_mean", "cv_f1_std"]].assign(task="variant"),
    service_ablation.drop_duplicates("masking")[["masking", "cv_f1_mean", "cv_f1_std"]].assign(task="service"),
], ignore_index=True)

PRESET_ORDER = ["NONE", "NAMES_ONLY", "STANDARD", "AGGRESSIVE"]
masking_ablation_chart = alt.Chart(ablation_summary).mark_line(point=True).encode(
    x=alt.X("masking:N", sort=PRESET_ORDER, title="Masking preset (left → right = stricter)"),
    y=alt.Y("cv_f1_mean:Q", title="Cross-validated macro-F1",
            scale=alt.Scale(domain=[0.88, 0.96])),
    color=alt.Color("task:N", title="Classifier"),
    tooltip=["task:N", "masking:N",
             alt.Tooltip("cv_f1_mean:Q", format=".3f"),
             alt.Tooltip("cv_f1_std:Q", format=".4f")],
).properties(
    width=500, height=280,
    title=alt.TitleParams(
        "Variant and service classifiers are robust to leakage masking",
        subtitle="F1 changes by < 0.005 across four progressively stricter presets",
        subtitleColor="#666", subtitleFontSize=11,
    ),
)
save_chart(masking_ablation_chart, str(FIGURE_DIR / 'rationale_classifier_masking_ablation.png'))
masking_ablation_chart

alt.Chart(...)

## 6.6 Stable Features Across Random Seeds

Top-feature rankings from a single classifier run are sensitive to the random seed when multiple correlated features carry similar signal. We run the classifier under five different seeds and keep features that appear in the top-15 for at least four runs.

This produces conservative, defensible feature lists rather than the snapshot of one run's decision boundary.


In [20]:
# Variant: stable features across 5 seeds, STANDARD masking
masked = apply_masking(long_df, text_col="rationale_raw", config=PRESET_STANDARD,
                       out_col="_masked")
texts_std = masked["_masked"].tolist()

variant_stable = stable_features(
    texts=texts_std,
    y=masked["variant"].to_numpy(),
    class_names=list(ENGLISH_VARIANTS),
    seeds=(5, 42, 100, 200, 500),
    top_n=15,
    min_appearances=4,
)
print("\n══ VARIANT — features in top-15 of at least 4/5 seeds ══")
for variant in ENGLISH_VARIANTS:
    print(f"\n  {variant.upper()}:")
    for term, count in variant_stable[variant][:15]:
        print(f"    {term:<35}  ({count}/5 runs)")

service_stable = stable_features(
    texts=texts_std,
    y=masked["service"].to_numpy(),
    class_names=list(SERVICES),
    seeds=(5, 42, 100, 200, 500),
    top_n=15,
    min_appearances=4,
)
print("\n\n══ SERVICE — features in top-15 of at least 4/5 seeds ══")
for svc in SERVICES:
    print(f"\n  {svc.upper()}:")
    for term, count in service_stable[svc][:15]:
        print(f"    {term:<35}  ({count}/5 runs)")


══ VARIANT — features in top-15 of at least 4/5 seeds ══

  MINIMAL:
    github                               (5/5 runs)
    search                               (5/5 runs)
    translation based                    (5/5 runs)
    translated                           (5/5 runs)
    translation using                    (5/5 runs)
    direct                               (5/5 runs)
    translation combines                 (5/5 runs)
    query                                (5/5 runs)
    contexts                             (5/5 runs)
    scholarship                          (5/5 runs)
    search query                         (5/5 runs)
    standard translation                 (5/5 runs)
    combination aims                     (5/5 runs)
    iso code                             (5/5 runs)
    translation captures                 (5/5 runs)

  GITHUB_SEARCHER:
    translations                         (5/5 runs)
    proposed                             (5/5 runs)
    choice                



══ SERVICE — features in top-15 of at least 4/5 seeds ══

  CLAUDE:
    follows                              (5/5 runs)
    terminology                          (5/5 runs)
    alternative                          (5/5 runs)
    academic                             (5/5 runs)
    human                                (5/5 runs)
    sciences                             (5/5 runs)
    patterns                             (5/5 runs)
    academic terminology                 (5/5 runs)
    knowledge                            (5/5 runs)
    technical                            (5/5 runs)
    github                               (5/5 runs)
    established                          (5/5 runs)
    computational                        (5/5 runs)
    learning                             (5/5 runs)
    typically                            (5/5 runs)

  OPENAI:
    reflecting                           (5/5 runs)
    standard                             (5/5 runs)
    field                          

In [21]:
# Save stable-feature tables to CSV for the paper
stable_rows = []
for variant, pairs in variant_stable.items():
    for rank, (term, count) in enumerate(pairs, 1):
        stable_rows.append({"task": "variant", "class": variant,
                           "rank": rank, "term": term, "appearances": count})
for svc, pairs in service_stable.items():
    for rank, (term, count) in enumerate(pairs, 1):
        stable_rows.append({"task": "service", "class": svc,
                           "rank": rank, "term": term, "appearances": count})

stable_df = pd.DataFrame(stable_rows)
stable_df.to_csv(os.path.join(EVAL_DIR, "stable_features.csv"), index=False)
print(f"→ Saved {os.path.join(EVAL_DIR, 'stable_features.csv')} ({len(stable_df)} rows)")

→ Saved /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/datasets/translated_terms/digital_humanities/evaluation/stable_features.csv (165 rows)


## 6.7 Joint Service-Variant Classifier

The marginal classifiers in §6.3 and §6.4 each perform strongly (variant ≈ 0.90 macro-F1, service ≈ 0.94), but they look at one axis at a time. The joint task — predict 24 service-variant combinations (8 services × 3 prompts) from rationale text — surfaces the *interaction*. Are services equally identifiable under every prompt? Are prompts equally identifiable across every service? Or do certain combinations partially collapse together?

If the marginals were fully independent, the joint classifier would score near the product of their accuracies. A meaningful drop, with the lost accuracy concentrated in particular combinations, tells you where prompt and service identity stop being separable.


In [22]:
# Joint label: 24 classes (8 services × 3 variants)
long_df["service_variant"] = long_df["service"] + "_" + long_df["variant"]
JOINT_ORDER = sorted(long_df["service_variant"].unique())

texts_jt = long_df["rationale_clean"].tolist()
y_jt = long_df["service_variant"].to_numpy()
X_jt, vec_jt = build_tfidf(texts_jt)
clf_jt, cv_jt, oof_jt = train_classifier(X_jt, y_jt)

print(f"Joint classifier macro-F1: {cv_jt.mean():.3f} ± {cv_jt.std():.3f}")
print(f"Per-fold: {[round(s, 3) for s in cv_jt]}")
print()
print(f"Compare to marginals:")
print(f"  Variant classifier (3 classes):  {cv_var.mean():.3f} (§6.3)")
print(f"  Service classifier (8 classes):  {cv_svc.mean():.3f} (§6.4)")
print(f"  Joint classifier  (24 classes):  {cv_jt.mean():.3f}")
print()
print(f"The joint task is harder than either marginal task. The next cells locate")
print(f"where prompt and service identities become difficult to separate.")

Joint classifier macro-F1: 0.859 ± 0.008
Per-fold: [np.float64(0.873), np.float64(0.859), np.float64(0.855), np.float64(0.851), np.float64(0.856)]

Compare to marginals:
  Variant classifier (3 classes):  0.896 (§6.3)
  Service classifier (8 classes):  0.942 (§6.4)
  Joint classifier  (24 classes):  0.859

The joint task is harder than either marginal task. The next cells locate
where prompt and service identities become difficult to separate.


In [23]:
# Confusion matrix — recall-normalised (% of true class)
cm_jt_df = confusion_df(y_jt, oof_jt, labels=JOINT_ORDER)

base_jt = alt.Chart(cm_jt_df).encode(
    x=alt.X("predicted:N", sort=JOINT_ORDER, title="Predicted",
            axis=alt.Axis(labelAngle=-45)),
    y=alt.Y("true:N", sort=JOINT_ORDER, title="True"),
    tooltip=["true:N", "predicted:N", "n:Q",
             alt.Tooltip("pct:Q", format=".1f", title="% of true class")],
)
rect_jt = base_jt.mark_rect().encode(
    color=alt.Color("pct:Q", scale=alt.Scale(scheme="blues"),
                    title="% of true class"),
)
text_jt = base_jt.mark_text(fontSize=10).encode(
    text=alt.Text("pct:Q", format=".0f"),
    color=alt.condition(alt.datum.pct > 50, alt.value("white"), alt.value("black")),
)
joint_classifier_chart = (rect_jt + text_jt).properties(
    width=420, height=380,
    title=alt.TitleParams(
        "Joint service-variant classifier — out-of-fold confusion matrix (% of true class)",
        subtitle="Each cell is recall-normalised; diagonal = correct predictions per class.",
        subtitleColor="#666", subtitleFontSize=11,
    ),
)
save_chart(joint_classifier_chart, str(FIGURE_DIR / 'rationale_joint_service_variant_confusion_matrix.png'))
joint_classifier_chart

alt.LayerChart(...)

In [24]:
# Top off-diagonal cells — where does the joint classifier confuse classes? Look only at cells with at least 2% error rate; below that is noise at this sample size.
ERROR_FLOOR = 2.0

off_diag = (
    cm_jt_df[
        (cm_jt_df["true"] != cm_jt_df["predicted"])
        & (cm_jt_df["pct"] >= ERROR_FLOOR)
    ]
    .sort_values("pct", ascending=False)
)

print(f"Off-diagonal cells with ≥{ERROR_FLOOR}% error rate (top-15):")
print(off_diag.head(15).to_string(index=False))
print()

# Look at how many top-15 confusions involve each variant — does any variant disproportionately drive the joint classifier's errors?
top15 = off_diag.head(15).copy()
top15["true_variant"] = top15["true"].str.split("_").str[1:].str.join("_")
top15["pred_variant"] = top15["predicted"].str.split("_").str[1:].str.join("_")

print()
print("Variant involvement in top-15 confusions:")
for variant in ["minimal", "github_searcher", "judge"]:
    n = ((top15["true_variant"] == variant) | (top15["pred_variant"] == variant)).sum()
    print(f"  {variant:<18} appears in {n}/15 top confusions")

Off-diagonal cells with ≥2.0% error rate (top-15):
                   true                predicted   n  pct
 gemini_github_searcher           gemini_minimal 149 17.6
        mistral_minimal  mistral_github_searcher 142 17.2
 claude_github_searcher           claude_minimal 145 16.5
         openai_minimal   openai_github_searcher 119 14.9
         gemini_minimal   gemini_github_searcher 108 12.8
   qwen_github_searcher             qwen_minimal 112 12.7
 openai_github_searcher           openai_minimal 100 11.5
           qwen_minimal     qwen_github_searcher  88 10.1
mistral_github_searcher          mistral_minimal  85  9.6
          llama_minimal    llama_github_searcher  73  9.4
          gemma_minimal    gemma_github_searcher  76  8.8
  llama_github_searcher            llama_minimal  61  7.7
  gemma_github_searcher            gemma_minimal  50  5.7
   qwen_github_searcher deepseek_github_searcher  49  5.6
  llama_github_searcher  mistral_github_searcher  41  5.2


Variant involvement

### Reading the confusion matrix

The 24-class classifier reaches 0.859 macro-F1, below both marginal classifiers. The drop is not uniformly distributed. Looking at the off-diagonal cells:

The largest confusions are between `minimal` and `github_searcher` rationales from the same service: Gemini, Claude, OpenAI, Qwen, Mistral, Llama, and Gemma all show this pattern. The `judge` prompt appears in none of the fifteen largest off-diagonal cells. A smaller number of errors cross service boundaries, especially among GitHub-search rationales.

Read methodologically: **the judge prompt creates the most distinctive rationale genre, while minimal and GitHub-search prompts often retain a shared service-specific register.** Prompt and service identity are therefore both recoverable, but they are not independent layers.

This qualifies the marginal-classifier finding. The familiar claim that "each LLM has a voice" is incomplete: the observable voice emerges from an interaction between model and task framing.


### Why I Do Not Predict Interpretive Categories from Rationales

An earlier version of this notebook tried to predict causal disagreement types from rationale text. I abandoned that approach because the labels were partly produced from keywords in those same rationales. A supervised model would therefore recover the features used to construct its target rather than supply independent evidence.

The revised pipeline avoids that circularity. The scripted comparison layer assigns only a descriptive string-level `comparison_status`: exact convergence, near-form convergence, substantive variation, or insufficient comparison. Rationale signals such as claims that no equivalent exists remain separate evidence fields. This notebook can therefore ask whether rationale prose varies by service and prompt without treating the models' explanations as validation of their translations.

This is methodologically useful in its own right. Rationale text is better suited to studying prompt and model style than to establishing why translations differ. The variant, service, and joint classifiers above remain appropriate because their labels are independent metadata rather than conclusions derived from the rationale text.

## 6.8 Translation × Rationale Convergence — the 2×2 Frame

The supervised classifiers above are diagnostic: they tell us what's recoverable from rationale text. A complementary descriptive view asks whether translation convergence and rationale convergence track each other.

For each language we have two axes already in `disagreement_analysis.csv`:

- **Translation convergence**: whether all four services produced the same string (`n_unique_raw == 1`).
- **Rationale convergence**: mean pairwise rationale similarity, split at the median (~0.21).

Crossing the two axes produces a 2×2 frame. If rationales validated translations, we would expect translation-convergent languages to also be rationale-convergent — and translation-divergent languages to be rationale-divergent. The empirical pattern is more interesting.


In [25]:
# Both axes are already in analysis_df — no additional computation needed
twox2_df = analysis_df[
    ['language_code', 'language_name', 'language_family', 'comparison_status',
     'n_unique_raw', 'mean_rationale_similarity', 'has_wikipedia']
].dropna(subset=['mean_rationale_similarity', 'n_unique_raw']).copy()

print(f'Languages with both axes: {len(twox2_df):,}')
print(f'\nn_unique_raw distribution:')
print(twox2_df['n_unique_raw'].value_counts().sort_index())
print(f'\nmean_rationale_similarity:')
print(twox2_df['mean_rationale_similarity'].describe().round(3))

# Quadrant thresholds:
#   Translation: n_unique_raw == 1 is the natural "all services agree" boundary
#   Rationale:   median split (no natural zero for cosine similarity)
rat_thresh = twox2_df['mean_rationale_similarity'].median()
print(f'\nRationale similarity median (threshold): {rat_thresh:.3f}')

def assign_quadrant(row):
    lo_trans = row['n_unique_raw'] == 1
    hi_rat   = row['mean_rationale_similarity'] >= rat_thresh
    if   lo_trans and hi_rat:       return 'Converge / Converge'
    elif lo_trans and not hi_rat:   return 'Converge / Diverge'
    elif not lo_trans and hi_rat:   return 'Diverge / Converge'
    else:                           return 'Diverge / Diverge'

twox2_df['quadrant'] = twox2_df.apply(assign_quadrant, axis=1)
print('\nQuadrant distribution:')
print(twox2_df['quadrant'].value_counts())

Languages with both axes: 881

n_unique_raw distribution:
n_unique_raw
1       5
2       2
3      17
4      62
5     102
6     154
7     193
8     245
9      61
10     36
11      4
Name: count, dtype: int64

mean_rationale_similarity:
count    881.000
mean       0.267
std        0.046
min        0.150
25%        0.236
50%        0.263
75%        0.294
max        0.456
Name: mean_rationale_similarity, dtype: float64

Rationale similarity median (threshold): 0.263

Quadrant distribution:
quadrant
Diverge / Diverge      439
Diverge / Converge     437
Converge / Converge      4
Converge / Diverge       1
Name: count, dtype: int64


In [26]:
QUAD_ORDER  = ['Converge / Converge', 'Converge / Diverge',
               'Diverge / Converge', 'Diverge / Diverge']
STATUS_ORDER_7 = ['exact_convergence', 'near_form_convergence',
                  'substantive_variation', 'insufficient_comparison']

x_max = int(twox2_df['n_unique_raw'].max()) + 1  # 8 for current data
x_domain = [0.5, x_max - 0.5]

# Jitter n_unique_raw so points at the same x-value don't completely overlap
rng = np.random.default_rng(42)
twox2_df['trans_jitter'] = (
    twox2_df['n_unique_raw'] + rng.uniform(-0.2, 0.2, len(twox2_df))
)

# Background shading for each quadrant
quad_rects = pd.DataFrame([
    {'x1': x_domain[0], 'x2': 1.5,          'y1': rat_thresh, 'y2': 1.0,       'q': 'Converge / Converge'},
    {'x1': x_domain[0], 'x2': 1.5,          'y1': 0.0,        'y2': rat_thresh, 'q': 'Converge / Diverge'},
    {'x1': 1.5,          'x2': x_domain[1], 'y1': rat_thresh, 'y2': 1.0,       'q': 'Diverge / Converge'},
    {'x1': 1.5,          'x2': x_domain[1], 'y1': 0.0,        'y2': rat_thresh, 'q': 'Diverge / Diverge'},
])
shade = alt.Chart(quad_rects).mark_rect(opacity=0.07).encode(
    x=alt.X('x1:Q', scale=alt.Scale(domain=x_domain)),
    x2='x2:Q',
    y=alt.Y('y1:Q', scale=alt.Scale(domain=[0.0, 1.0])),
    y2='y2:Q',
    color=alt.Color('q:N', scale=alt.Scale(scheme='set2'), legend=None),
)
pts = alt.Chart(twox2_df).mark_circle(size=35, opacity=0.65).encode(
    x=alt.X('trans_jitter:Q',
            title='N unique translations (jittered; 1 = all services identical)',
            scale=alt.Scale(domain=x_domain),
            axis=alt.Axis(values=list(range(1, x_max)))),
    y=alt.Y('mean_rationale_similarity:Q',
            title='Mean rationale similarity (higher = services reason more alike)',
            scale=alt.Scale(domain=[0.0, 1.0])),
    color=alt.Color('comparison_status:N', sort=STATUS_ORDER_7,
                    scale=alt.Scale(scheme='tableau10'), title='Comparison status'),
    tooltip=['language_name:N', 'language_family:N', 'comparison_status:N',
             alt.Tooltip('n_unique_raw:Q', title='N unique translations'),
             alt.Tooltip('mean_rationale_similarity:Q', format='.3f', title='Rationale sim.'),
             'quadrant:N'],
)
hline = alt.Chart(pd.DataFrame({'y': [rat_thresh]})).mark_rule(
    strokeDash=[4, 2], color='#888', strokeWidth=1,
).encode(y='y:Q')
vline = alt.Chart(pd.DataFrame({'x': [1.5]})).mark_rule(
    strokeDash=[4, 2], color='#888', strokeWidth=1,
).encode(x='x:Q')

translation_rationale_convergence_chart = (
    (shade + pts + hline + vline)
    .resolve_scale(color='independent')
    .properties(
        width=620, height=440,
        title=alt.TitleParams(
            'Translation × Rationale Convergence — 2×2 Frame',
            subtitle=(
                'X = N unique translations across all services (1 = full consensus). '
                'Y = mean rationale similarity (higher = services reason alike).'
            ),
            subtitleColor='#666', subtitleFontSize=11,
        ),
    )
)
save_chart(translation_rationale_convergence_chart, str(FIGURE_DIR / 'translation_rationale_convergence.png'))
translation_rationale_convergence_chart

alt.LayerChart(...)

In [27]:
# Comparison-status composition per quadrant — what disagreement types map to each cell?
xq_long = (
    twox2_df.groupby(['quadrant', 'comparison_status']).size()
    .reset_index(name='n')
)
xq_long['pct'] = (
    xq_long.groupby('quadrant')['n']
    .transform(lambda x: x / x.sum() * 100)
    .round(1)
)

print('Comparison-status distribution per quadrant (% within quadrant):')
print(
    pd.crosstab(twox2_df['comparison_status'], twox2_df['quadrant'], normalize='columns')
    .mul(100).round(1).to_string()
)

alt.Chart(xq_long).mark_bar().encode(
    x=alt.X('quadrant:N', sort=QUAD_ORDER, title=None,
            axis=alt.Axis(labelAngle=-20)),
    y=alt.Y('pct:Q', title='% of quadrant'),
    color=alt.Color('comparison_status:N', sort=STATUS_ORDER_7,
                    scale=alt.Scale(scheme='tableau10'), title='Comparison status'),
    order=alt.Order('comparison_status:N', sort='ascending'),
    tooltip=['quadrant:N', 'comparison_status:N', 'n:Q',
             alt.Tooltip('pct:Q', format='.1f')],
).properties(
    width=520, height=300,
    title='Comparison-status composition per 2×2 quadrant',
)

Comparison-status distribution per quadrant (% within quadrant):
quadrant               Converge / Converge  Converge / Diverge  Diverge / Converge  Diverge / Diverge
comparison_status                                                                                    
exact_convergence                    100.0               100.0                 0.0                0.0
near_form_convergence                  0.0                 0.0                 0.7                0.0
substantive_variation                  0.0                 0.0                99.3              100.0


alt.Chart(...)

## 6.9 Rationale Embedding Projection

The TF-IDF classifiers above show that service and prompt variant are *recoverable* from rationale text. A sentence-embedding UMAP complements that finding with a spatial view: do rationales from the same service or variant genuinely cluster in dense-vector space, or does the classifier succeed by exploiting a handful of surface tokens?

Each point is one rationale (one language × service × English variant triple). We project the full 384-d sentence-transformer space to 2D and color by service, prompt variant, language family, and rationale length quartile.

In [28]:
from sentence_transformers import SentenceTransformer
import umap

CACHE_DIR = Path('..') / 'notebooks' / 'eda_cache'
CACHE_DIR.mkdir(exist_ok=True)

if 'rat_model' not in dir():
    rat_model = SentenceTransformer('all-MiniLM-L6-v2')
    print('Model loaded.')

def embed_with_cache_rat(texts, cache_name, batch_size=128):
    cache_path = CACHE_DIR / f'{cache_name}.npy'
    if cache_path.exists():
        cached = np.load(cache_path)
        if len(cached) == len(texts):
            print(f'Loading cached embeddings: {cache_path.name}')
            return cached
        print(f'Cache size mismatch ({len(cached)} vs {len(texts)}) — re-embedding.')
        cache_path.unlink()
    print(f'Encoding {len(texts):,} texts → {cache_path.name}')
    vecs = rat_model.encode(
        texts,
        batch_size=batch_size,
        show_progress_bar=True,
        convert_to_numpy=True,
        normalize_embeddings=True,
    )
    np.save(cache_path, vecs)
    return vecs

Model loaded.


In [29]:
rat_vecs = embed_with_cache_rat(
    long_df['rationale_clean'].tolist(),
    cache_name='rationale_vecs',
)

rat_reducer = umap.UMAP(
    n_neighbors=15,
    min_dist=0.1,
    n_components=2,
    metric='cosine',
    random_state=42,
)
rat_coords = rat_reducer.fit_transform(rat_vecs)

rat_umap_df = long_df[['language_code', 'language_name', 'language_family',
                        'service', 'variant', 'service_variant', 'rationale_raw']].copy()
rat_umap_df['umap_x'] = rat_coords[:, 0]
rat_umap_df['umap_y'] = rat_coords[:, 1]
rat_umap_df['rat_len'] = rat_umap_df['rationale_raw'].str.len()
rat_umap_df['rat_len_q'] = pd.qcut(
    rat_umap_df['rat_len'], q=4,
    labels=['Q1 (shortest)', 'Q2', 'Q3', 'Q4 (longest)'],
)

# Collapse rare language families to 'Other' for a readable legend
top_fams = rat_umap_df['language_family'].value_counts().head(9).index.tolist()
rat_umap_df['family_plot'] = rat_umap_df['language_family'].where(
    rat_umap_df['language_family'].isin(top_fams), 'Other'
)

print(f'Projection complete: {len(rat_umap_df):,} rationale points')
print(rat_umap_df[['service', 'variant']].value_counts().sort_index())

Loading cached embeddings: rationale_vecs.npy


/Users/zleblanc/.virtualenvs/coding-dh-env/lib/python3.13/site-packages/umap/umap_.py:1952: UserWarning: n_jobs value 1 overridden to 1 by setting random_state. Use no seed for parallelism.
  warn(


Projection complete: 20,661 rationale points
service   variant        
claude    github_searcher    880
          judge              881
          minimal            881
deepseek  github_searcher    875
          judge              881
          minimal            870
gemini    github_searcher    848
          judge              869
          minimal            846
gemma     github_searcher    870
          judge              881
          minimal            865
llama     github_searcher    791
          judge              878
          minimal            776
mistral   github_searcher    881
          judge              881
          minimal            825
openai    github_searcher    869
          judge              881
          minimal            797
qwen      github_searcher    880
          judge              881
          minimal            874
Name: count, dtype: int64


In [30]:
# ── Panel row 1: service / prompt variant / joint service×variant ─────────
ax79 = dict(
    x=alt.X('umap_x:Q', title='UMAP-1', axis=alt.Axis(labels=False, ticks=False)),
    y=alt.Y('umap_y:Q', title='UMAP-2', axis=alt.Axis(labels=False, ticks=False)),
)
tt79 = ['language_name:N', 'language_family:N', 'service:N', 'variant:N',
        alt.Tooltip('rat_len:Q', title='Rationale length (chars)')]

base79 = alt.Chart(rat_umap_df).mark_circle(size=18, opacity=0.55)

p_service = base79.encode(
    **ax79,
    color=alt.Color('service:N', scale=alt.Scale(scheme='tableau10'), title='Service'),
    tooltip=tt79,
).properties(width=250, height=250, title='By service')

p_variant = base79.encode(
    **ax79,
    color=alt.Color('variant:N', scale=alt.Scale(scheme='set2'), title='Prompt variant'),
    tooltip=tt79,
).properties(width=250, height=250, title='By prompt variant')

# Joint label already computed in §6.7 on long_df
SVC_VARIANT_ORDER = sorted(rat_umap_df['service_variant'].dropna().unique())
p_joint = base79.encode(
    **ax79,
    color=alt.Color('service_variant:N',
                    sort=SVC_VARIANT_ORDER,
                    scale=alt.Scale(scheme='tableau20'),
                    title='Service × variant'),
    tooltip=tt79 + ['service_variant:N'],
).properties(width=250, height=250, title='By service × variant')

rationale_space_chart = (p_service | p_variant | p_joint).properties(
    title=alt.TitleParams(
        'Rationale Space — Service & Prompt Structure',
        subtitle='Same UMAP coords across all panels (all-MiniLM-L6-v2, cosine).',
        subtitleColor='#666', subtitleFontSize=11,
    )
)
save_chart(rationale_space_chart, str(FIGURE_DIR / 'rationale_space_service_prompt_structure.png'))
rationale_space_chart

alt.HConcatChart(...)

In [31]:
# ── Panel row 2: language family / rationale length ───────────────────────
p_family = (
    alt.Chart(rat_umap_df).mark_circle(size=18, opacity=0.55).encode(
        **ax79,
        color=alt.Color('family_plot:N', scale=alt.Scale(scheme='tableau20'), title='Language family'),
        tooltip=tt79,
    ).properties(width=380, height=300, title='By language family')
)

p_length = base79.encode(
    **ax79,
    color=alt.Color('rat_len_q:N',
                    sort=['Q1 (shortest)', 'Q2', 'Q3', 'Q4 (longest)'],
                    scale=alt.Scale(scheme='blues'),
                    title='Length quartile'),
    tooltip=tt79,
).properties(width=380, height=300, title='By rationale length')

(p_family | p_length).properties(
    title=alt.TitleParams(
        'Rationale Space — Language & Length Context',
        subtitle='Same UMAP coords as above.',
        subtitleColor='#666', subtitleFontSize=11,
    )
)

alt.HConcatChart(...)